In [1]:
import nltk

# List of packages to download
packages = ['punkt', 'punkt_tab', 'wordnet', 'omw-1.4']

for package in packages:
    nltk.download(package)

[nltk_data] Downloading package punkt to
[nltk_data]     C:\Users\USER\AppData\Roaming\nltk_data...
[nltk_data]   Package punkt is already up-to-date!
[nltk_data] Downloading package punkt_tab to
[nltk_data]     C:\Users\USER\AppData\Roaming\nltk_data...
[nltk_data]   Package punkt_tab is already up-to-date!
[nltk_data] Downloading package wordnet to
[nltk_data]     C:\Users\USER\AppData\Roaming\nltk_data...
[nltk_data]   Package wordnet is already up-to-date!
[nltk_data] Downloading package omw-1.4 to
[nltk_data]     C:\Users\USER\AppData\Roaming\nltk_data...
[nltk_data]   Package omw-1.4 is already up-to-date!


In [2]:
from nltk.tokenize import word_tokenize
from nltk.stem import PorterStemmer,WordNetLemmatizer
from sklearn.feature_extraction.text import CountVectorizer,TfidfVectorizer

In [ ]:
import pandas as pd

path="../datasets/twitter.csv"
df=pd.read_csv(path,header=None,names=['tweet_id','entity','sentiment','text'])

df.head()

,tweet_id,entity,sentiment,text
0,2401,Borderlands,Positive,im getting on borderlands and i will murder yo...
1,2401,Borderlands,Positive,I am coming to the borders and I will kill you...
2,2401,Borderlands,Positive,im getting on borderlands and i will kill you ...
3,2401,Borderlands,Positive,im coming on borderlands and i will murder you...
4,2401,Borderlands,Positive,im getting on borderlands 2 and i will murder ...
5,2401,Borderlands,Positive,im getting into borderlands and i can murder y...
6,2402,Borderlands,Positive,So I spent a few hours making something for fu...
7,2402,Borderlands,Positive,So I spent a couple of hours doing something f...
8,2402,Borderlands,Positive,So I spent a few hours doing something for fun...
9,2402,Borderlands,Positive,So I spent a few hours making something for fu...


In [4]:
df.shape

(74682, 4)

In [5]:
df.info()

<class 'pandas.DataFrame'>
RangeIndex: 74682 entries, 0 to 74681
Data columns (total 4 columns):
 #   Column     Non-Null Count  Dtype
---  ------     --------------  -----
 0   tweet_id   74682 non-null  int64
 1   entity     74682 non-null  str  
 2   sentiment  74682 non-null  str  
 3   text       73996 non-null  str  
dtypes: int64(1), str(3)
memory usage: 2.3 MB


In [6]:
df.isna().sum()

tweet_id       0
entity         0
sentiment      0
text         686
dtype: int64

In [7]:
#Drop rows where 'text' is NaN
df.dropna(subset=['text'],inplace=True)

In [8]:
df.isnull().sum()

tweet_id     0
entity       0
sentiment    0
text         0
dtype: int64

In [9]:
# Reset the index (good practice after dropping rows)
df.reset_index(drop=True,inplace=True)

In [10]:
df.describe

<bound method NDFrame.describe of        tweet_id       entity sentiment  \
0          2401  Borderlands  Positive   
1          2401  Borderlands  Positive   
2          2401  Borderlands  Positive   
3          2401  Borderlands  Positive   
4          2401  Borderlands  Positive   
...         ...          ...       ...   
73991      9200       Nvidia  Positive   
73992      9200       Nvidia  Positive   
73993      9200       Nvidia  Positive   
73994      9200       Nvidia  Positive   
73995      9200       Nvidia  Positive   

                                                    text  
0      im getting on borderlands and i will murder yo...  
1      I am coming to the borders and I will kill you...  
2      im getting on borderlands and i will kill you ...  
3      im coming on borderlands and i will murder you...  
4      im getting on borderlands 2 and i will murder ...  
...                                                  ...  
73991  Just realized that the Windows partition 

In [11]:
df.columns

Index(['tweet_id', 'entity', 'sentiment', 'text'], dtype='str')

In [12]:
df["sentiment"].value_counts()

sentiment
Negative      22358
Positive      20655
Neutral       18108
Irrelevant    12875
Name: count, dtype: int64

In [40]:
df["text"] = df["text"].str.lower()

In [41]:
import re
def clean_text(text):
    text=re.sub(r"https?://\S+|www\.\S+"," ",text)
    text=re.sub(r"@\w+"," ",text)
    text=re.sub(r"#"," ",text)
    text=re.sub(r"&\w+"," ",text)
    text=re.sub(r"\d+"," ",text)
    text=re.sub(r"^[a-z\s]"," ",text)
    text=re.sub(r"\s+"," ",text).strip()
    
    return text

In [42]:
df["text"]=df["text"].apply(clean_text)

In [43]:
df.head()

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,getting on borderlands and i will murder you a...,"mgettingonborderlandandiwillmurderyouall,"
1,2401,Borderlands,Positive,"am coming to the borders and i will kill you all,","IamcomingtotheborderandIwillkillyouall,"
2,2401,Borderlands,Positive,"getting on borderlands and i will kill you all,","mgettingonborderlandandiwillkillyouall,"
3,2401,Borderlands,Positive,"coming on borderlands and i will murder you all,","mcomingonborderlandandiwillmurderyouall,"
4,2401,Borderlands,Positive,getting on borderlands and i will murder you m...,"mgettingonborderlandandiwillmurderyoumeall,"


In [44]:
df['text']

0        getting on borderlands and i will murder you a...
1        am coming to the borders and i will kill you all,
2          getting on borderlands and i will kill you all,
3         coming on borderlands and i will murder you all,
4        getting on borderlands and i will murder you m...
                               ...                        
73991    ust realized that the windows partition of my ...
73992    ust realized that my mac window partition is y...
73993    ust realized the windows partition of my mac i...
73994    ust realized between the windows partition of ...
73995    ust like the windows partition of my mac is li...
Name: text, Length: 73996, dtype: str

In [45]:
df["tokens"]=df["text"].apply(word_tokenize)

In [46]:
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,getting on borderlands and i will murder you a...,"[getting, on, borderlands, and, i, will, murde..."
1,2401,Borderlands,Positive,"am coming to the borders and i will kill you all,","[am, coming, to, the, borders, and, i, will, k..."
2,2401,Borderlands,Positive,"getting on borderlands and i will kill you all,","[getting, on, borderlands, and, i, will, kill,..."
3,2401,Borderlands,Positive,"coming on borderlands and i will murder you all,","[coming, on, borderlands, and, i, will, murder..."
4,2401,Borderlands,Positive,getting on borderlands and i will murder you m...,"[getting, on, borderlands, and, i, will, murde..."
...,...,...,...,...,...
73991,9200,Nvidia,Positive,ust realized that the windows partition of my ...,"[ust, realized, that, the, windows, partition,..."
73992,9200,Nvidia,Positive,ust realized that my mac window partition is y...,"[ust, realized, that, my, mac, window, partiti..."
73993,9200,Nvidia,Positive,ust realized the windows partition of my mac i...,"[ust, realized, the, windows, partition, of, m..."
73994,9200,Nvidia,Positive,ust realized between the windows partition of ...,"[ust, realized, between, the, windows, partiti..."


In [47]:
stemmer = PorterStemmer()
df['tokens'] = df['tokens'].apply(lambda toks: [stemmer.stem(t) for t in toks])
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,getting on borderlands and i will murder you a...,"[get, on, borderland, and, i, will, murder, yo..."
1,2401,Borderlands,Positive,"am coming to the borders and i will kill you all,","[am, come, to, the, border, and, i, will, kill..."
2,2401,Borderlands,Positive,"getting on borderlands and i will kill you all,","[get, on, borderland, and, i, will, kill, you,..."
3,2401,Borderlands,Positive,"coming on borderlands and i will murder you all,","[come, on, borderland, and, i, will, murder, y..."
4,2401,Borderlands,Positive,getting on borderlands and i will murder you m...,"[get, on, borderland, and, i, will, murder, yo..."
...,...,...,...,...,...
73991,9200,Nvidia,Positive,ust realized that the windows partition of my ...,"[ust, realiz, that, the, window, partit, of, m..."
73992,9200,Nvidia,Positive,ust realized that my mac window partition is y...,"[ust, realiz, that, my, mac, window, partit, i..."
73993,9200,Nvidia,Positive,ust realized the windows partition of my mac i...,"[ust, realiz, the, window, partit, of, my, mac..."
73994,9200,Nvidia,Positive,ust realized between the windows partition of ...,"[ust, realiz, between, the, window, partit, of..."


In [48]:
lemmatizer= WordNetLemmatizer()

# Lemmatize each token
df["tokens"]=df["tokens"].apply(lambda toks: [lemmatizer.lemmatize(t) for t in toks])

# Join the tokens back into a sentence
df['tokens'] = df["tokens"].apply(' '.join)
df

,tweet_id,entity,sentiment,text,tokens
0,2401,Borderlands,Positive,getting on borderlands and i will murder you a...,"get on borderland and i will murder you all ,"
1,2401,Borderlands,Positive,"am coming to the borders and i will kill you all,","am come to the border and i will kill you all ,"
2,2401,Borderlands,Positive,"getting on borderlands and i will kill you all,","get on borderland and i will kill you all ,"
3,2401,Borderlands,Positive,"coming on borderlands and i will murder you all,","come on borderland and i will murder you all ,"
4,2401,Borderlands,Positive,getting on borderlands and i will murder you m...,"get on borderland and i will murder you me all ,"
...,...,...,...,...,...
73991,9200,Nvidia,Positive,ust realized that the windows partition of my ...,ust realiz that the window partit of my mac is...
73992,9200,Nvidia,Positive,ust realized that my mac window partition is y...,ust realiz that my mac window partit is year b...
73993,9200,Nvidia,Positive,ust realized the windows partition of my mac i...,ust realiz the window partit of my mac is now ...
73994,9200,Nvidia,Positive,ust realized between the windows partition of ...,ust realiz between the window partit of my mac...


In [49]:
tfidf=TfidfVectorizer(max_features=5000)
X_tfidf=tfidf.fit_transform(df["tokens"])

In [50]:
X_tfidf

<Compressed Sparse Row sparse matrix of dtype 'float64'
	with 1077093 stored elements and shape (73996, 5000)>

In [51]:
df["sentiment"].value_counts()

sentiment
Negative      22358
Positive      20655
Neutral       18108
Irrelevant    12875
Name: count, dtype: int64

In [52]:
from sklearn.preprocessing import LabelEncoder

label_eoncoder=LabelEncoder()
y_encoded=label_eoncoder.fit_transform(df["sentiment"])
print(label_eoncoder.classes_)

['Irrelevant' 'Negative' 'Neutral' 'Positive']


In [53]:
num_class=len(label_eoncoder.classes_)
print(num_class)

4


In [54]:
df["tokens"]

0            get on borderland and i will murder you all ,
1          am come to the border and i will kill you all ,
2              get on borderland and i will kill you all ,
3           come on borderland and i will murder you all ,
4         get on borderland and i will murder you me all ,
                               ...                        
73991    ust realiz that the window partit of my mac is...
73992    ust realiz that my mac window partit is year b...
73993    ust realiz the window partit of my mac is now ...
73994    ust realiz between the window partit of my mac...
73995    ust like the window partit of my mac is like y...
Name: tokens, Length: 73996, dtype: str

In [56]:
all_words=" ".join(df["tokens"]).split()
print(all_words)

['get', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'all', ',', 'am', 'come', 'to', 'the', 'border', 'and', 'i', 'will', 'kill', 'you', 'all', ',', 'get', 'on', 'borderland', 'and', 'i', 'will', 'kill', 'you', 'all', ',', 'come', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'all', ',', 'get', 'on', 'borderland', 'and', 'i', 'will', 'murder', 'you', 'me', 'all', ',', 'get', 'into', 'borderland', 'and', 'i', 'can', 'murder', 'you', 'all', ',', 'o', 'i', 'spent', 'a', 'few', 'hour', 'make', 'someth', 'for', 'fun', '.', '.', '.', 'if', 'you', 'do', "n't", 'know', 'i', 'am', 'a', 'huge', 'fan', 'and', 'maya', 'is', 'one', 'of', 'my', 'favorit', 'charact', '.', 'so', 'i', 'decid', 'to', 'make', 'myself', 'a', 'wallpap', 'for', 'my', 'pc', '.', '.', 'here', 'is', 'the', 'origin', 'imag', 'versu', 'the', 'creation', 'i', 'made', ':', ')', 'enjoy', '!', 'pic.twitter.com/mlsi', 'wf', 'jg', 'o', 'i', 'spent', 'a', 'coupl', 'of', 'hour', 'do', 'someth', 'for', 'fun', '...'

In [57]:
unique_words = sorted(list(set(all_words)))
print(unique_words)

['!', '$', '%', '&', "'", "''", "'-", "'-microsoft", "'d", "'ll", "'m", "'n", "'re", "'s", "'t", "'ve", "'′", '(', ')', '*', '+', '+++', '+-', '+befor', '+j', '+shit', '+sunni', '+thank', ',', '-', '--', '-.', '-_-', '-a', '-alecib', '-aleksib', '-amazon', '-amp', '-an-hour', '-and-xbox-', '-and-xbox-s…', '-ankc', '-apex', '-appl', '-ash', '-backlit', '-baloch', '-ban', '-bat', '-berkshir', '-best-play', '-best-plays…', '-bit', '-bit/nvidia', '-bomb', '-book', '-boy', '-bristol-my', '-bt', '-c', '-caus', '-check', '-christian', '-crore', '-d', '-da', '-day', '-day-old', '-da…', '-dead', '-decks.net/hearthstone-du', '-dg', '-dg+webcam', '-do', '-ed', '-eleven', '-elsa', '-end', '-exercis', '-facebook', '-ff', '-finger', '-foot', '-game', '-gari', '-go', '-googl', '-go…', '-guild', '-h', '-hall', '-halo', '-hard', '-harri', '-he', '-hentaithick', '-hi', '-hour', '-how', '-huh', '-hunt', '-h…', '-in-', '-inch', '-input', '-insidesport.co', '-insidesport.co/fifa-updates-f', '-insidesport.c

In [59]:
vocab={word:i+1 for i, word in enumerate(unique_words)}
vocab_size=len(vocab)+1
print(vocab_size)

32395


In [60]:
print(vocab)

{'!': 1, '$': 2, '%': 3, '&': 4, "'": 5, "''": 6, "'-": 7, "'-microsoft": 8, "'d": 9, "'ll": 10, "'m": 11, "'n": 12, "'re": 13, "'s": 14, "'t": 15, "'ve": 16, "'′": 17, '(': 18, ')': 19, '*': 20, '+': 21, '+++': 22, '+-': 23, '+befor': 24, '+j': 25, '+shit': 26, '+sunni': 27, '+thank': 28, ',': 29, '-': 30, '--': 31, '-.': 32, '-_-': 33, '-a': 34, '-alecib': 35, '-aleksib': 36, '-amazon': 37, '-amp': 38, '-an-hour': 39, '-and-xbox-': 40, '-and-xbox-s…': 41, '-ankc': 42, '-apex': 43, '-appl': 44, '-ash': 45, '-backlit': 46, '-baloch': 47, '-ban': 48, '-bat': 49, '-berkshir': 50, '-best-play': 51, '-best-plays…': 52, '-bit': 53, '-bit/nvidia': 54, '-bomb': 55, '-book': 56, '-boy': 57, '-bristol-my': 58, '-bt': 59, '-c': 60, '-caus': 61, '-check': 62, '-christian': 63, '-crore': 64, '-d': 65, '-da': 66, '-day': 67, '-day-old': 68, '-da…': 69, '-dead': 70, '-decks.net/hearthstone-du': 71, '-dg': 72, '-dg+webcam': 73, '-do': 74, '-ed': 75, '-eleven': 76, '-elsa': 77, '-end': 78, '-exercis':

In [61]:
X_sequences=[]
for sentence in df["tokens"]: #to remove duplicate value 
    seq=[vocab[word] for word in sentence.split() if word in vocab]
    X_sequences.append(seq)

In [62]:
for i , seq in enumerate(X_sequences):
    print(seq) #vocab id

[10689, 18995, 3789, 1707, 12696, 30497, 17436, 31450, 1397, 29]
[1512, 5465, 27400, 26837, 3787, 1707, 12696, 30497, 14621, 31450, 1397, 29]
[10689, 18995, 3789, 1707, 12696, 30497, 14621, 31450, 1397, 29]
[5465, 18995, 3789, 1707, 12696, 30497, 17436, 31450, 1397, 29]
[10689, 18995, 3789, 1707, 12696, 30497, 17436, 31450, 16435, 1397, 29]
[10689, 13461, 3789, 1707, 12696, 4427, 17436, 31450, 1397, 29]
[18629, 12696, 25409, 785, 9400, 12470, 16073, 25224, 9798, 10214, 239, 239, 239, 12874, 31450, 7299, 17573, 14734, 12696, 1512, 785, 12572, 9135, 1707, 16362, 13596, 19059, 18767, 17510, 9226, 4843, 239, 25139, 12696, 6602, 27400, 16073, 17550, 785, 29985, 9798, 17510, 19962, 239, 239, 12049, 13596, 26837, 19325, 13021, 29552, 26837, 5953, 12696, 16003, 727, 19, 8387, 1, 20625, 30322, 14035]
[18629, 12696, 25409, 785, 5840, 18767, 12470, 7299, 25224, 9798, 10214, 241, 12874, 31450, 7299, 17573, 14734, 26810, 12696, 11, 785, 12572, 742, 3789, 9135, 1707, 16362, 13596, 19059, 18767, 1751

In [63]:
import numpy as np

max_len=100
x_padded=np.zeros((len(X_sequences),max_len),dtype=np.int32)
print(x_padded)

[[0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 ...
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]
 [0 0 0 ... 0 0 0]]


In [68]:
for i, seq in enumerate(X_sequences):
    if len(seq) > 0:
        x_padded[i, : len(seq[:max_len])] = seq[:max_len]

In [69]:
print(x_padded)

[[10689 18995  3789 ...     0     0     0]
 [ 1512  5465 27400 ...     0     0     0]
 [10689 18995  3789 ...     0     0     0]
 ...
 [29156 22486 26837 ...     0     0     0]
 [29156 22486  3221 ...     0     0     0]
 [29156 15363 26837 ...     0     0     0]]


In [70]:
from sklearn.model_selection import train_test_split

x_train,x_test,y_train,y_test=train_test_split(x_padded,y_encoded,test_size=0.2,random_state=42,stratify=y_encoded)
print(x_train)

[[19343 13596  4446 ...     0     0     0]
 [ 6292 30069 13596 ...     0     0     0]
 [23739  9011 15699 ...     0     0     0]
 ...
 [11747 29948   785 ...     0     0     0]
 [   18 15129    19 ...     0     0     0]
 [23091 23091 23091 ...     0     0     0]]


In [72]:
import torch
from torch.utils.data import DataLoader,TensorDataset

train_dataset=TensorDataset(torch.tensor(x_train,dtype=torch.long),torch.tensor(y_train,dtype=torch.long))

test_dataset=TensorDataset(torch.tensor(x_test,dtype=torch.long),torch.tensor(y_test,dtype=torch.long))

In [73]:
batch_size=64
train_loader=DataLoader(train_dataset,batch_size=batch_size,shuffle=True)
test_loader=DataLoader(train_dataset,batch_size=batch_size,shuffle=False)

In [74]:
device=torch.device("cuda" if torch.cuda.is_available() else"cpu")
print(f"using device: {device}")

using device: cpu


In [75]:
import torch.nn as nn

class SimpleRNN(nn.Module):
    def __init__(self, vocab_size, embedding_dim,hidden_dim,output_dim):
        super().__init__()
        self.embedding=nn.Embedding(vocab_size,embedding_dim,padding_idx=0)
        self.rnn=nn.RNN(embedding_dim,hidden_dim,batch_first=True)
        self.fc=nn.Linear(hidden_dim,output_dim)
    
    def forward(self,text):
        embedded=self.embedding(text)
        out,hidden=self.rnn(embedded)
        final_hidden=hidden[-1]
        return self.fc(final_hidden)

In [76]:
EMBEDDING_DIM=100
HIDDEN_DIM=128
OUTPUT_DIM=4

model=SimpleRNN(vocab_size,EMBEDDING_DIM,HIDDEN_DIM,OUTPUT_DIM).to(device)
print(model)

criterion=nn.CrossEntropyLoss()

optimizer = torch.optim.Adam(
    model.parameters(),
    lr=0.001
)

SimpleRNN(
  (embedding): Embedding(32395, 100, padding_idx=0)
  (rnn): RNN(100, 128, batch_first=True)
  (fc): Linear(in_features=128, out_features=4, bias=True)
)


In [ ]:
epochs=5

for epoch in range(epochs):
    model.train()
    
    epoch_loss = 0
    correct = 0
    total = 0
    
    for texts,labels in train_loader:
        texts,labels=texts.to(device),labels.to(device)
        
        optimizer.zero_grad()
        predictions=model(texts)
        loss=criterion(predictions,labels)
        
        loss.backward()
        optimizer.step()
        
        epoch_loss +=loss.item()
        _,predicted=torch.max(predictions.data,1)
        total+=labels.size(0)
        correct+=(predicted==labels).sum().item()
        
    accuracy=100*correct/total
    print(f"Epoch {epoch+1:02d}/{epochs:02d} | Loss:{epoch_loss/len(train_loader):.4f} | Train Accuracy:{accuracy:.2f}%")

In [ ]:
model.eval()
test_correct=0
test_total=0

with torch.no_grad():
    for texts,labels in test_loader:
        texts=texts.to(device)
        labels = labels.to(device)
        
        predictions = model(texts)
        _, predicted = torch.max(predictions.data, 1)
        test_total += labels.size(0)
        test_correct += (predicted == labels).sum().item()
        
test_accuracy = 100 * test_correct / test_total
print(f"\nFinal Test Accuracy: {test_accuracy:.2f}%")